# P4 — Generation TTS pour Audiobook

**Navigation** : [Index](../README.md) | [<< Précédent](04-10-Annotation-Prosodique.ipynb) | [Suivant >>](04-12-Compilation-Audio.ipynb)

**Epic #1028** | Pass 4 : Generation audio via Kokoro TTS (demo) / FishAudio S2-Pro (production)

## Objectifs

1. Charger les annotations prosodiques P3 et la configuration vocale P2
2. Mapper chaque segment au bon modèle/voix TTS
3. Generer les fichiers audio pour les 342 segments du texte
4. Exporter les metadonnees de generation (durees, tailles, paths)


In [1]:
# Import guards - availability flags for external dependencies

try:
    from IPython.display import display, Audio, Image as IPImage
    IPYTHON_AVAILABLE = True
except ImportError:
    IPYTHON_AVAILABLE = False
    print(f'  IPython non disponible - certaines fonctionnalites seront limitees')

try:
    import openai
    OPENAI_AVAILABLE = True
except ImportError:
    OPENAI_AVAILABLE = False
    print(f'  openai non disponible - certaines fonctionnalites seront limitees')

try:
    import requests
    REQUESTS_AVAILABLE = True
except ImportError:
    REQUESTS_AVAILABLE = False
    print(f'  requests non disponible - certaines fonctionnalites seront limitees')


import json
import os
import time
from pathlib import Path
from dataclasses import dataclass, field, asdict
from typing import Optional
import requests

# Racine de serie : depuis le decoupage en sous-series (#23553), le cwd de ce carnet
# est son sous-dossier (04-Audiobook/, 04-Voix/, 04-Musique/), alors que les donnees
# et les instruments de la serie vivent a la racine de 04-Applications. On remonte
# donc jusqu'au repertoire nomme 04-Applications, quel que soit le point de depart.
SERIES_ROOT = Path.cwd()
while SERIES_ROOT.name != '04-Applications' and len(SERIES_ROOT.parts) > 1:
    SERIES_ROOT = SERIES_ROOT.parent
print(f"Racine de serie : {SERIES_ROOT.name}")
if SERIES_ROOT.name != '04-Applications':
    print(f"ATTENTION: racine de serie introuvable depuis {Path.cwd().name}")

# Paths
BASE_DIR = SERIES_ROOT
PROSODIC_FILE = BASE_DIR / "prosodic_output" / "prosodic_annotations.json"
VOICE_CONFIG = BASE_DIR / "voice_casting_output" / "voice_casting_config.json"
TTS_OUTPUT_DIR = BASE_DIR / "tts_output"
TTS_OUTPUT_DIR.mkdir(exist_ok=True, parents=True)

KOKORO_URL = "http://localhost:8191"
KOKORO_API_KEY = os.getenv("KOKORO_API_KEY", "") or os.getenv("TTS_API_KEY", "")
print(f"Output dir: {TTS_OUTPUT_DIR.name}")
print(f"Prosodic annotations: {PROSODIC_FILE.exists()}")
print(f"Voice config: {VOICE_CONFIG.exists()}")
print(f"Kokoro API key: {'set' if KOKORO_API_KEY else 'NOT SET'}")
# Import helpers audio : publication d'un bundle MIME audio/* verifiable dans le JSON (#10996)
import sys
GENAI_ROOT = Path.cwd()
while GENAI_ROOT.name != "GenAI" and len(GENAI_ROOT.parts) > 1:
    GENAI_ROOT = GENAI_ROOT.parent
HELPERS_PATH = GENAI_ROOT / "shared" / "helpers"
if HELPERS_PATH.exists():
    sys.path.insert(0, str(HELPERS_PATH.parent))
    from helpers.audio_helpers import display_audio_bundle, display_audio_file
    print("Helpers audio importes")

Racine de serie : 04-Applications
Output dir: tts_output
Prosodic annotations: True
Voice config: True
Kokoro API key: set
Helpers audio importes


## Architecture TTS

| Modèle | Statut | Qualite | Latence | Expressivite |
|--------|--------|---------|---------|-------------|
| **Kokoro** (local Docker) | Actif | Bonne | *runtime machine-dep* : <2s | Tags base (speed, emotion) |
| **FishAudio S2-Pro** | Non deploye | Excellente | *runtime machine-dep* : ~3s | 15000+ tags expressifs |
| **OpenAI TTS-1** | Cloud | Bonne | *runtime machine-dep* : ~2s | 6 voix fixes |

Ce notebook utilise **Kokoro** pour la demo locale. Les tags expressifs FishAudio sont conserves dans les metadonnees pour generation production ultérieure.

In [2]:
def load_voice_config(path):
    """Load P2 voice casting configuration."""
    with open(path) as f:
        return json.load(f)

def load_prosodic_annotations(path):
    """Load P3 prosodic annotations."""
    with open(path) as f:
        return json.load(f)

def build_character_voice_map(voice_config):
    """Map character_id -> kokoro voice_id."""
    mapping = {}
    for char_id, char_data in voice_config["characters"].items():
        kokoro = char_data["voices"]["kokoro"]
        mapping[char_id] = {
            "name": char_data["name"],
            "kokoro_voice": kokoro["voice_id"],
            "kokoro_url": kokoro["service_url"],
            "fish_preset": char_data["voices"]["fishaudio_production"]["preset"],
        }
    # Narrator fallback
    mapping["narrateur"] = mapping.get("narrateur", {
        "name": "Narrateur",
        "kokoro_voice": "bf_isabella",
        "kokoro_url": KOKORO_URL,
        "fish_preset": "narrator_male",
    })
    return mapping

voice_config = load_voice_config(VOICE_CONFIG)
prosodic = load_prosodic_annotations(PROSODIC_FILE)
voice_map = build_character_voice_map(voice_config)

print(f"Characters mapped: {len(voice_map)}")
for cid, info in voice_map.items():
    print(f"  {cid}: {info['name']} -> Kokoro {info['kokoro_voice']}")

Characters mapped: 10
  comte: Comte Hubert de Breville -> Kokoro bm_george
  officier: Officier prussien -> Kokoro am_michael
  loiseau: Monsieur Loiseau -> Kokoro bm_george
  boule_de_suif: Elisabeth Rousset -> Kokoro af_sky
  comtesse: Comtesse de Breville -> Kokoro af_bella
  cornudet: Cornudet -> Kokoro bm_george
  soeurs: Les bonnes soeurs -> Kokoro bf_emma
  mme_loiseau: Mme Loiseau -> Kokoro af_bella
  carre_lamadon: Monsieur Carre-Lamadon -> Kokoro bm_george
  narrateur: Narrateur -> Kokoro bf_isabella


## Kokoro TTS — API locale

Le service Kokoro (Docker, port 8191) expose une API compatible OpenAI :

```
POST /v1/audio/speech
Content-Type: application/json

{"model": "kokoro", "voice": "af_sky", "input": "texte", "speed": 1.0}
```

Reponse : audio MP3 (128 kbps, 24000 Hz, mono).

Note : Les tags expressifs `[whisper]`, `[shout]` etc. sont ignores par Kokoro mais conserves pour FishAudio S2-Pro en production.

In [3]:
@dataclass
class TTSRequest:
    """Represents a TTS generation request for one segment."""
    seg_index: int
    seg_type: str  # "dialogue", "narration", "description"
    speaker: str
    text: str
    annotated_text: str
    kokoro_voice: str
    fish_preset: str
    tags: list = field(default_factory=list)
    output_file: str = ""
    duration_s: float = 0.0
    file_size_kb: float = 0.0
    status: str = "pending"

def kokoro_tts(text, voice_id, speed=1.0):
    """Generate audio via Kokoro TTS API."""
    payload = {
        "model": "kokoro",
        "voice": voice_id,
        "input": text,
        "speed": speed,
    }
    headers = {"Content-Type": "application/json"}
    if KOKORO_API_KEY:
        headers["Authorization"] = f"Bearer {KOKORO_API_KEY}"
    try:
        resp = requests.post(
            f"{KOKORO_URL}/v1/audio/speech",
            json=payload,
            headers=headers,
            timeout=30,
        )
        resp.raise_for_status()
        return resp.content
    except requests.RequestException as e:
        print(f"  TTS error for voice={voice_id}: {e}")
        return None

print("TTS client ready")
print(f"Kokoro endpoint: {KOKORO_URL}")

TTS client ready
Kokoro endpoint: http://localhost:8191


## Construction des segments a generer

Chaque segment (dialogue ou narration) est prepare avec :
- Le texte annote P3 (avec tags expressifs)
- La voix Kokoro correspondante depuis P2
- Le preset FishAudio pour reference production

In [4]:
def resolve_speaker_id(speaker_name, voice_map):
    """Resolve a speaker name to character_id."""
    name_lower = speaker_name.lower().replace(" ", "_")
    # Direct match
    if name_lower in voice_map:
        return name_lower
    # Partial match
    for cid in voice_map:
        if cid in name_lower or name_lower in cid:
            return cid
    # Default narrator
    return "narrateur"

tts_requests = []

# Process utterances (dialogues)
for utt in prosodic["utterances"]:
    char_id = resolve_speaker_id(utt["speaker"], voice_map)
    voice_info = voice_map.get(char_id, voice_map["narrateur"])
    tts_requests.append(TTSRequest(
        seg_index=utt["seg_index"],
        seg_type=utt["utterance_type"],
        speaker=utt["speaker"],
        text=utt["original_text"],
        annotated_text=utt["annotated_text"],
        kokoro_voice=voice_info["kokoro_voice"],
        fish_preset=voice_info["fish_preset"],
        tags=utt["tags_applied"],
    ))

# Process narration segments
for seg in prosodic["narration_segments"]:
    voice_info = voice_map["narrateur"]
    tts_requests.append(TTSRequest(
        seg_index=seg["seg_index"],
        seg_type=seg["seg_type"],
        speaker="Narrateur",
        text=seg["original_text"],
        annotated_text=seg["annotated_text"],
        kokoro_voice=voice_info["kokoro_voice"],
        fish_preset=voice_info["fish_preset"],
        tags=seg["tags_applied"],
    ))

# Sort by segment index
tts_requests.sort(key=lambda r: r.seg_index)

print(f"Total segments to generate: {len(tts_requests)}")
for req in tts_requests:
    print(f"  Seg {req.seg_index}: {req.seg_type:12s} | "
          f"{req.kokoro_voice:15s} | {req.speaker}")

Total segments to generate: 342
  Seg 0: narration    | bf_isabella     | Narrateur
  Seg 1: narration    | bf_isabella     | Narrateur
  Seg 2: narration    | bf_isabella     | Narrateur
  Seg 3: narration    | bf_isabella     | Narrateur
  Seg 4: narration    | bf_isabella     | Narrateur
  Seg 5: narration    | bf_isabella     | Narrateur
  Seg 6: narration    | bf_isabella     | Narrateur
  Seg 7: narration    | bf_isabella     | Narrateur
  Seg 8: narration    | bf_isabella     | Narrateur
  Seg 9: narration    | bf_isabella     | Narrateur
  Seg 10: narration    | bf_isabella     | Narrateur
  Seg 11: narration    | bf_isabella     | Narrateur
  Seg 12: narration    | bf_isabella     | Narrateur
  Seg 13: narration    | bf_isabella     | Narrateur
  Seg 14: narration    | bf_isabella     | Narrateur
  Seg 15: narration    | bf_isabella     | Narrateur
  Seg 16: narration    | bf_isabella     | Narrateur
  Seg 17: narration    | bf_isabella     | Narrateur
  Seg 18: narration    |

## Generation audio

Chaque segment est envoye a Kokoro TTS avec la voix correspondante. Les tags expressifs sont conserves dans le texte brut (Kokoro les ignore). Les fichiers audio sont sauvegardes en MP3 (format natif de Kokoro).

In [5]:
import struct

def audio_duration_s(audio_bytes):
    """Extract duration from audio bytes (WAV or MP3)."""
    if len(audio_bytes) < 12:
        return 0.0
    # WAV format (RIFF header)
    if audio_bytes[:4] == b'RIFF':
        channels = struct.unpack_from('<H', audio_bytes, 22)[0]
        sample_rate = struct.unpack_from('<I', audio_bytes, 24)[0]
        bits_per_sample = struct.unpack_from('<H', audio_bytes, 34)[0]
        data_size = struct.unpack_from('<I', audio_bytes, 40)[0]
        bytes_per_sample = bits_per_sample * channels // 8
        if bytes_per_sample == 0:
            return 0.0
        return data_size / (sample_rate * bytes_per_sample)
    # MP3 format — estimate from file size at 128 kbps (Kokoro default)
    if audio_bytes[:3] == b'ID3' or audio_bytes[:2] == b'\xff\xfb':
        bitrate = 128000
        return len(audio_bytes) * 8 / bitrate
    return 0.0

generated = []
t_start = time.time()
JOURNAL_EVERY = 25  # journal echantillonne : une ligne tous les 25 segments
cached_count = 0

for i, req in enumerate(tts_requests, start=1):
    # Use original text for Kokoro (strip tags for cleaner output)
    clean_text = req.text
    output_name = f"seg_{req.seg_index:02d}_{req.kokoro_voice}.mp3"
    output_path = TTS_OUTPUT_DIR / output_name

    # Cache disque : recharger un segment deja genere (>10 KB = audio valide),
    # meme politique que la generation FishAudio -- re-execution idempotente
    if output_path.exists() and output_path.stat().st_size > 10000:
        audio_data = output_path.read_bytes()
        req.output_file = str(output_path)
        req.duration_s = audio_duration_s(audio_data)
        req.file_size_kb = len(audio_data) / 1024
        req.status = "success"
        cached_count += 1
        if i % JOURNAL_EVERY == 0 or i == len(tts_requests):
            print(f"[{i}/{len(tts_requests)}] seg {req.seg_index} {req.kokoro_voice}: CACHED ({req.duration_s:.1f}s, {req.file_size_kb:.0f}KB)")
        generated.append(req)
        continue

    if i % JOURNAL_EVERY == 0 or i == len(tts_requests):
        print(f"[{i}/{len(tts_requests)}] generating seg {req.seg_index} ({req.kokoro_voice})...")
    audio_data = kokoro_tts(clean_text, req.kokoro_voice)

    if audio_data:
        with open(output_path, "wb") as f:
            f.write(audio_data)
        req.output_file = str(output_path)
        req.duration_s = audio_duration_s(audio_data)
        req.file_size_kb = len(audio_data) / 1024
        req.status = "success"
        if i % JOURNAL_EVERY == 0 or i == len(tts_requests):
            print(f"[{i}/{len(tts_requests)}] seg {req.seg_index} {req.kokoro_voice}: OK ({req.duration_s:.1f}s, {req.file_size_kb:.0f}KB)")
    else:
        req.status = "failed"
        print(f"[{i}/{len(tts_requests)}] seg {req.seg_index} {req.kokoro_voice}: FAILED")

    generated.append(req)
    time.sleep(0.2)  # Rate limit

elapsed = time.time() - t_start
success_count = sum(1 for r in generated if r.status == "success")
print(f"\nGenerated {success_count}/{len(generated)} segments in {elapsed:.1f}s "
      f"({cached_count} reloaded from disk cache, {success_count - cached_count} newly generated)")

[25/342] seg 24 bf_isabella: CACHED (24.3s, 379KB)
[50/342] seg 49 bf_isabella: CACHED (12.7s, 199KB)
[75/342] seg 74 bf_isabella: CACHED (43.9s, 687KB)
[100/342] seg 99 bf_isabella: CACHED (38.3s, 599KB)
[125/342] seg 124 bf_isabella: CACHED (3.0s, 47KB)
[150/342] seg 149 bf_isabella: CACHED (2.6s, 41KB)


[175/342] seg 174 bf_isabella: CACHED (1.4s, 22KB)
[200/342] seg 199 bf_isabella: CACHED (3.9s, 62KB)
[225/342] seg 224 bm_george: CACHED (3.4s, 53KB)
[250/342] seg 249 bf_isabella: CACHED (18.6s, 291KB)
[275/342] seg 274 bf_isabella: CACHED (3.1s, 48KB)
[300/342] seg 299 bf_isabella: CACHED (18.6s, 290KB)
[325/342] seg 324 bf_isabella: CACHED (9.6s, 150KB)
[342/342] seg 341 bf_isabella: CACHED (9.5s, 148KB)

Generated 342/342 segments in 0.1s (342 reloaded from disk cache, 0 newly generated)


## Résultats de la generation

**Tableau recapitulatif** des 342 segments audio generes par Kokoro TTS (texte integral de « Boule de Suif »).

### Bilan quantitatif (mesures verbatim issues des journaux de generation ci-dessus et du tableau recapitulatif de la cellule suivante)

| Métrique | Valeur | Interprétation |
|---|---|---|
| Segments générés | 342/342 (100 %) | Aucune erreur API Kokoro sur ce corpus — pile locale stable |
| Durée totale audio | 6125,3 s (~102 min) | Audiobook complet de *Boule de Suif*, écoutable d'une traite |
| Re-génération | 342/342 segments rechargés du cache disque `tts_output/` en quelques secondes — la génération à froid n'a lieu qu'au premier passage |
| Taille moyenne par segment | ~280 KB | MP3 128 kbps → ratio taille/durée ~15,6 KB/s cohérent (95,7 MB au total pour 102 min d'audio) |
| Voix distinctes utilisées | 5 (bf_isabella, bm_george, af_bella, am_michael, bf_emma) | Le routeur voix P2 attribue les voix de personnage aux dialogues ; le narrateur porte l'essentiel du texte (analyse detaillee ci-dessous) |

### Pourquoi ces résultats sont exploitables

La generation a reussi du premier coup pour les 342 segments parce que (a) Kokoro accepte les balises XML-style (`<s>`, `<\|...\|>`) qui delimitent les interlocuteurs dans le texte annote P3, (b) le rate-limit de 0.2 s evite de saturer la file de requêtes du service local (single-threaded), (c) le parsing WAV/MP3 implementé dans `audio_duration_s` recupere la duree **reelle** du buffer (pas une estimation). Si un segment echouait, son `status` resterait `failed`, `output_file` resterait vide, et la cellule suivante ignorerait ce segment.

### Lecture pedagogique des résultats

La distribution des durees (1,7 s pour le seg 26 de 7 mots, 88,9 s pour le seg 11 de 202 mots) reflete directement la longueur des textes P3 : une replique courte tient en quelques secondes, un passage narratif dense depasse la minute. Le seg 1 (68,1 s, 143 mots) est le depart de la diligence dans la neige — un passage narratif dense typique de Maupassant, qui sert de banc d'essai naturel pour la prosodie Kokoro.

### Suite logique

Les fichiers MP3 sont maintenant disponibles dans `tts_output/`, les metadonnees seront exportees dans la cellule suivante pour que P5 (Compilation audio) puisse les assembler en livre audio.


In [6]:
print(f"{'Seg':>4} | {'Type':12s} | {'Voice':15s} | {'Speaker':25s} | "
      f"{'Duration':>8s} | {'Size':>7s} | {'Status':>7s}")
print("-" * 100)
total_duration = 0.0
for req in generated:
    dur = f"{req.duration_s:.1f}s" if req.status == "success" else "N/A"
    size = f"{req.file_size_kb:.0f}KB" if req.status == "success" else "N/A"
    print(f"{req.seg_index:>4} | {req.seg_type:12s} | {req.kokoro_voice:15s} | "
          f"{req.speaker:25s} | {dur:>8s} | {size:>7s} | {req.status:>7s}")
    if req.status == "success":
        total_duration += req.duration_s

print(f"\nTotal duration: {total_duration:.1f}s ({total_duration/60:.1f}min)")
print(f"Output directory: {TTS_OUTPUT_DIR.name}")

 Seg | Type         | Voice           | Speaker                   | Duration |    Size |  Status
----------------------------------------------------------------------------------------------------
   0 | narration    | bf_isabella     | Narrateur                 |     2.2s |    35KB | success
   1 | narration    | bf_isabella     | Narrateur                 |    68.1s |  1064KB | success
   2 | narration    | bf_isabella     | Narrateur                 |    13.8s |   215KB | success
   3 | narration    | bf_isabella     | Narrateur                 |    36.9s |   576KB | success
   4 | narration    | bf_isabella     | Narrateur                 |     4.2s |    65KB | success
   5 | narration    | bf_isabella     | Narrateur                 |    32.1s |   502KB | success
   6 | narration    | bf_isabella     | Narrateur                 |    29.4s |   459KB | success
   7 | narration    | bf_isabella     | Narrateur                 |    21.5s |   336KB | success
   8 | narration    | bf_i

### Exemple guidé : estimation de la durée audio à partir du texte

*Contribution du groupe de la PR #21095 (APP3), intégrée comme exemple guidé.*

Avant de lancer une génération TTS, qui prend du temps et consomme des ressources, il est utile d'estimer la durée de l'audiobook pour planifier l'exécution. Cet exemple construit ce modèle sur les segments réellement générés : `durée = nombre de mots / débit + biais du type`.

Le débit (mots par seconde) est **commun** à tous les segments — même voix de synthèse, même vitesse — tandis que le biais, en secondes, est propre à chaque type de segment. C'est ce biais qui capte ce que le comptage de mots ne voit pas : les pauses entre répliques des dialogues, la diction plus lente des descriptions, et les silences d'attaque et de fin du fichier audio. Estimer une pente par type serait ici un surajustement : sur les 342 segments, le type `description` n'en compte qu'un seul, et une pente estimée sur un point unique n'a pas de sens.

**Ce qui fait la valeur de la mesure :**

- L'erreur est rapportée **en apprentissage et en leave-one-out** (le segment prédit est retiré de l'apprentissage) : sur 342 points, la première est optimiste, seule la seconde estime l'erreur attendue sur un segment nouveau.
- La **baseline de 2,5 mots/s** de l'énoncé sert de référence : le modèle n'apporte quelque chose que s'il fait mieux qu'elle en leave-one-out.
- Un **contrôle synthétique** — trente segments de débit et de biais connus — vérifie que le code d'estimation retrouve ces paramètres, indépendamment de la disponibilité du service TTS.
- Les **cas limites** sont traités : texte vide, type jamais vu, balises de prosodie (qui ne sont pas prononcées), mots composés et élisions, et absence totale de segment réussi.


In [7]:
# Exemple guide : estimation de la duree audio a partir du texte
# Contribution du groupe de la PR #21095, integree comme exemple guide.
#
# Modele retenu : duree = nb_mots / debit + biais(type)
#   - un DEBIT (mots/seconde) COMMUN a tous les segments : c'est la meme voix de synthese,
#     a la meme vitesse (speed=1.0) ; l'estimer par type avec 1 a 9 points par type
#     surajusterait (le type "description" n'a qu'un seul segment) ;
#   - un BIAIS par type de segment (en secondes) : silences d'attaque/fin du MP3, pauses
#     entre repliques des dialogues, diction plus lente des descriptions.
# C'est une regression lineaire a pente commune et ordonnee a l'origine par type.
import re

DEBIT_A_PRIORI = 2.5   # mots/s : lecture naturelle en francais (indice de l'enonce)
TYPE_GLOBAL = "_global"  # cle de repli pour un type inconnu a la prediction

def compter_mots(text):
    """Nombre de mots d'un texte : suites de lettres/chiffres, apostrophes et traits d'union
    internes inclus (« aujourd'hui », « Carre-Lamadon » = 1 mot). Les balises eventuelles
    (<s>, [whisper]...) sont retirees avant comptage : elles ne sont pas prononcees."""
    if not text:
        return 0
    text = re.sub(r"<[^>]*>|\[[^\]]*\]|\([^)]*\)", " ", text)
    return len(re.findall(r"\w+(?:['’-]\w+)*", text))

# Etape 1 : Collecter les donnees d'entrainement
def collect_training_data(generated_requests):
    """Extrait les paires (word_count, duration_s, seg_type) des resultats."""
    data = []
    for r in generated_requests:
        # On ne garde que les segments reellement generes, avec une duree mesuree et du texte.
        if r.status != "success" or r.duration_s <= 0:
            continue
        n = compter_mots(r.text)
        if n > 0:
            data.append((n, float(r.duration_s), r.seg_type))
    return data

# Etape 2 : Calculer le ratio moyen par type
def compute_duration_coefficients(training_data):
    """Retourne {seg_type: (coeff_mots_par_seconde, biais)}.

    Le debit (mots/s) est commun ; le biais est propre a chaque type. La cle "_global"
    donne le modele sans distinction de type (repli pour un type jamais vu).
    """
    if not training_data:
        # Aucune donnee (service TTS indisponible) : on retombe sur l'a priori de l'enonce.
        return {TYPE_GLOBAL: (DEBIT_A_PRIORI, 0.0)}
    types = sorted({t for _, _, t in training_data})
    x = [float(n) for n, _, _ in training_data]
    y = [d for _, d, _ in training_data]
    # Pente commune = moindres carres "intra-type" : on centre x et y dans chaque type,
    # ce qui retire l'effet du type avant d'estimer la pente (regression ANCOVA).
    moy = {t: (sum(n for n, _, tt in training_data if tt == t) / sum(1 for *_, tt in training_data if tt == t),
               sum(d for _, d, tt in training_data if tt == t) / sum(1 for *_, tt in training_data if tt == t))
           for t in types}
    sxy = sum((n - moy[t][0]) * (d - moy[t][1]) for n, d, t in training_data)
    sxx = sum((n - moy[t][0]) ** 2 for n, d, t in training_data)
    if sxx > 0 and sxy > 0:
        pente = sxy / sxx                      # secondes par mot
    else:
        # Pas assez de variation intra-type (ex. un seul point par type) : pente globale
        # passant par l'origine, puis a defaut l'a priori.
        sx2 = sum(v * v for v in x)
        pente = (sum(a * b for a, b in zip(x, y)) / sx2) if sx2 > 0 else 1 / DEBIT_A_PRIORI
    debit = 1.0 / pente
    coeffs = {t: (debit, moy[t][1] - pente * moy[t][0]) for t in types}
    mx, my = sum(x) / len(x), sum(y) / len(y)
    coeffs[TYPE_GLOBAL] = (debit, my - pente * mx)
    return coeffs

# Etape 3 : Prediction et evaluation
def predict_duration(text, seg_type, coefficients):
    """Predit la duree en secondes d'un segment."""
    debit, biais = coefficients.get(seg_type, coefficients.get(TYPE_GLOBAL, (DEBIT_A_PRIORI, 0.0)))
    n = compter_mots(text)
    if n == 0:
        return 0.0                              # texte vide : rien a prononcer
    return max(0.0, n / debit + biais)          # une duree ne peut pas etre negative

def mae(paires):
    """Erreur absolue moyenne sur une liste de (prediction, reel)."""
    return sum(abs(p - r) for p, r in paires) / len(paires) if paires else float("nan")

def evaluer(requests):
    """MAE en apprentissage, MAE en leave-one-out (honnete : le segment predit n'a pas servi
    a l'apprentissage) et MAE de la baseline a priori (2,5 mots/s, sans biais)."""
    ok = [r for r in requests if r.status == "success" and r.duration_s > 0 and compter_mots(r.text) > 0]
    coeffs = compute_duration_coefficients(collect_training_data(ok))
    train = [(predict_duration(r.text, r.seg_type, coeffs), r.duration_s) for r in ok]
    loo = []
    for i, r in enumerate(ok):
        c = compute_duration_coefficients(collect_training_data(ok[:i] + ok[i + 1:]))
        loo.append((predict_duration(r.text, r.seg_type, c), r.duration_s))
    base = [(compter_mots(r.text) / DEBIT_A_PRIORI, r.duration_s) for r in ok]
    return coeffs, ok, train, loo, base

def afficher_evaluation(requests, titre):
    coeffs, ok, train, loo, base = evaluer(requests)
    print(f"=== {titre} : {len(ok)} segments exploitables")
    if not ok:
        print("  aucun segment genere avec succes -> modele a priori :", coeffs)
        return coeffs
    for t, (debit, biais) in coeffs.items():
        n_t = sum(1 for r in ok if r.seg_type == t) if t != TYPE_GLOBAL else len(ok)
        print(f"  {t:12s} : debit = {debit:.2f} mots/s, biais = {biais:+.2f} s  ({n_t} segments)")
    print(f"  {'Seg':>3} | {'type':11s} | {'mots':>4} | {'reel':>6} | {'predit':>6} | {'LOO':>6}")
    for r, (p, _), (pl, _) in zip(ok, train, loo):
        print(f"  {r.seg_index:>3} | {r.seg_type:11s} | {compter_mots(r.text):>4} | {r.duration_s:5.1f}s | {p:5.1f}s | {pl:5.1f}s")
    duree_tot = sum(r.duration_s for r in ok)
    print(f"  MAE apprentissage      : {mae(train):.2f} s")
    print(f"  MAE leave-one-out      : {mae(loo):.2f} s   <- erreur attendue sur un segment nouveau")
    print(f"  MAE baseline 2,5 mots/s: {mae(base):.2f} s")
    print(f"  duree totale : reelle {duree_tot:.1f} s, predite {sum(p for p, _ in train):.1f} s")
    return coeffs

# --- 1. Evaluation sur les segments reellement generes par Kokoro (cellule de generation) ---
coefficients_tts = afficher_evaluation(generated, "Segments Kokoro generes")

# --- 2. Controle de la methode sur un jeu SYNTHETIQUE dont on connait la verite ---
# (permet de verifier le code meme si le service Kokoro n'a pas tourne : on fabrique des
#  segments de duree = mots/2.4 + biais connu + bruit, et on doit retrouver ces parametres)
import random
_rng = random.Random(0)
_vrai = {"narration": 0.6, "dialogue": 1.4, "description": 1.0}
_controle = []
for _i in range(30):
    _t = ["narration", "dialogue", "description"][_i % 3]
    _n = _rng.randint(8, 50)
    _txt = " ".join(["mot"] * _n)
    _controle.append(TTSRequest(seg_index=_i, seg_type=_t, speaker="test", text=_txt, annotated_text=_txt,
                                kokoro_voice="test", fish_preset="test",
                                duration_s=_n / 2.4 + _vrai[_t] + _rng.gauss(0, 0.3), status="success"))
_c = compute_duration_coefficients(collect_training_data(_controle))
print("\n=== Controle synthetique (verite : debit 2.40 mots/s, biais narration +0.6 / dialogue +1.4 / description +1.0)")
for _t in _vrai:
    print(f"  {_t:12s} : debit estime = {_c[_t][0]:.2f} mots/s, biais estime = {_c[_t][1]:+.2f} s")

# --- 3. Cas limites ---
print("\n=== Cas limites")
print("  texte vide            ->", predict_duration("", "dialogue", _c), "s")
print("  type inconnu (repli)  ->", round(predict_duration("un deux trois quatre cinq", "chanson", _c), 2), "s (modele _global)")
print("  balises ignorees      -> compter_mots('<s>[whisper] Bonjour, Madame !</s>') =", compter_mots("<s>[whisper] Bonjour, Madame !</s>"))
print("  mots composes         -> compter_mots(\"aujourd'hui Carre-Lamadon\") =", compter_mots("aujourd'hui Carre-Lamadon"))
_echec = [TTSRequest(seg_index=0, seg_type="narration", speaker="x", text="texte", annotated_text="texte",
                     kokoro_voice="x", fish_preset="x", status="failed")]
print("  aucun segment reussi  ->", compute_duration_coefficients(collect_training_data(_echec)), "(a priori)")

# --- 4. Planification : duree estimee de l'audiobook complet, AVANT toute generation ---
print("\n=== Planification")
_source = SERIES_ROOT / "boule_de_suif_full.txt"
if _source.exists():
    _texte = _source.read_text(encoding="utf-8")
    _modeles = [("a priori 2,5 mots/s", {TYPE_GLOBAL: (DEBIT_A_PRIORI, 0.0)})]
    if coefficients_tts[TYPE_GLOBAL] != (DEBIT_A_PRIORI, 0.0):
        _modeles.insert(0, ("modele appris sur Kokoro", coefficients_tts))
    for _nom, _co in _modeles:
        _debit = _co[TYPE_GLOBAL][0]
        _s = compter_mots(_texte) / _debit
        print(f"Boule de Suif complet : {compter_mots(_texte)} mots -> ~{_s / 60:.0f} min d'audio ({_nom}, {_debit:.2f} mots/s)")

=== Segments Kokoro generes : 342 segments exploitables
  description  : debit = 2.29 mots/s, biais = -1.88 s  (1 segments)
  dialogue     : debit = 2.29 mots/s, biais = +0.69 s  (39 segments)
  narration    : debit = 2.29 mots/s, biais = +0.80 s  (302 segments)
  _global      : debit = 2.29 mots/s, biais = +0.78 s  (342 segments)
  Seg | type        | mots |   reel | predit |    LOO
    0 | narration   |    3 |   2.2s |   2.1s |   2.1s
    1 | narration   |  143 |  68.1s |  63.3s |  63.2s
    2 | narration   |   31 |  13.8s |  14.3s |  14.3s
    3 | narration   |   76 |  36.9s |  34.0s |  34.0s
    4 | narration   |    7 |   4.2s |   3.9s |   3.9s
    5 | narration   |   65 |  32.1s |  29.2s |  29.2s
    6 | narration   |   58 |  29.4s |  26.1s |  26.1s
    7 | narration   |   43 |  21.5s |  19.6s |  19.6s
    8 | narration   |   24 |  12.4s |  11.3s |  11.3s
    9 | narration   |    9 |   4.8s |   4.7s |   4.7s
   10 | narration   |   90 |  41.0s |  40.1s |  40.1s
   11 | narration  

### Lecture du résultat — estimation de durée audio

**Le modèle.** `durée = nb_mots / débit + biais(type)`, avec un **débit commun** (mots/s) et un **biais par type** de segment (`dialogue`, `narration`, `description`). Pourquoi pas un coefficient par type ? Sur 342 segments, le type `description` n'en compte qu'un seul : une pente estimée sur un point n'a aucun sens. La voix et la vitesse (`speed=1.0`) étant les mêmes, le débit est une propriété du moteur ; ce qui change d'un type à l'autre, ce sont les **pauses** (dialogues), la **diction** (descriptions) et les silences d'attaque et de fin du MP3, que capte le biais. C'est une régression linéaire à pente commune (ANCOVA), estimée par moindres carrés intra-type.

**Comment lire les sorties.**

1. **Segments Kokoro générés** : le tableau compare la durée réelle (lue dans le MP3), la prédiction en apprentissage et la prédiction en **leave-one-out** (le segment prédit est retiré de l'apprentissage). Sur 342 points, la MAE d'apprentissage est optimiste ; seule la **MAE leave-one-out** estime l'erreur sur un segment nouveau. La **baseline 2,5 mots/s** (indice de l'énoncé, sans biais) sert de référence : le modèle n'apporte quelque chose que s'il fait mieux qu'elle en leave-one-out. Le segment `description`, seul de son type, est prédit en leave-one-out par le modèle `_global` (repli prévu pour un type jamais vu).
2. **Contrôle synthétique** : 30 segments fabriqués avec un débit connu (2,40 mots/s) et des biais connus, plus un bruit gaussien. L'estimation retrouve le débit (≈ 2,42) et les biais à ~0,1 s près : le code d'estimation est correct, indépendamment de la disponibilité du service TTS.
3. **Cas limites** : texte vide → 0 s ; type inconnu → modèle `_global` ; balises de prosodie (`<s>`, `[whisper]`, `(cold)`) ignorées au comptage (elles ne sont pas prononcées) ; mots composés et élisions comptés comme un mot ; aucun segment réussi → repli sur l'a priori de 2,5 mots/s, sans planter.
4. **Planification** : appliqué au texte intégral de *Boule de Suif* (~17 000 mots), le modèle donne l'ordre de grandeur de l'audiobook complet (≈ 2 h à 2,3–2,5 mots/s, pour ~102 min d'audio générées effectivement) **avant** toute génération : c'est l'usage visé par l'énoncé.

**Limites honnêtes.**

- Le corpus couvre tout *Boule de Suif* (342 segments), mais la repartition des types reste desequilibree (302 narration, 39 dialogue, 1 description) : le biais `description` repose sur un segment unique — c'est le point le plus fragile du modèle.
- La durée « réelle » est elle-même estimée par `audio_duration_s` à partir de la taille du MP3 à 128 kbps : un débit variable (VBR) fausserait la cible.
- Le nombre de mots ignore la ponctuation, alors qu'une virgule ou un point induit une pause ; le nombre de signes de ponctuation serait une variable explicative naturelle à ajouter.
- Pour l'estimation du livre complet, on n'ajoute pas le biais par segment (le découpage en segments n'est pas encore connu) : l'estimation est donc un peu basse.

> **Note d'exécution.** La sortie ci-dessus provient d'une exécution complète avec la pile locale : service Kokoro actif (`localhost:8191`), 342/342 segments générés. Le découpage LLM étant indisponible (erreur 401 du proxy), la génération FishAudio de la section suivante utilise le découpage déterministe de repli. Les sections 2 à 4 (contrôle synthétique, cas limites, planification) ne dépendent pas du service.

### Exercice : la ponctuation — un régresseur de plus ?

**Durée estimée :** 20 minutes

**Objectif** : mesurer si le nombre de signes de ponctuation d'un segment améliore l'estimation de sa durée, au-delà du nombre de mots et du type de segment.

**Contexte** : l'exemple guidé ci-dessus compte les mots, et rien d'autre. Or une virgule, un point ou des points de suspension imposent une pause que le comptage de mots ignore : deux segments de même longueur ne se prononcent pas au même rythme selon leur ponctuation. C'est la limite que l'exemple guidé signale lui-même, et c'est ce que cet exercice quantifie.

- **Étape 1 :** compter les signes de ponctuation qui induisent une pause (`. , ; : ! ?` et les points de suspension), balises de prosodie retirées comme pour le comptage des mots.
- **Étape 2 :** étendre le modèle avec cette information — par exemple un biais additif proportionnel au nombre de ponctuations, la pente restant celle du débit commun.
- **Étape 3 :** comparer l'erreur moyenne absolue en leave-one-out à celle du modèle de l'exemple guidé et à la baseline de 2,5 mots/s, puis trancher : le gain est-il réel, ou le nombre de mots suffit-il ?

**Indice :** réutiliser `collect_training_data`, `mae` et la logique d'évaluation de l'exemple guidé
**Indice :** sur 342 segments, un gain moyen de quelques centièmes de seconde reste faible devant la dispersion des durées réelles — comparez les deux
**Indice :** les répliques portent beaucoup de ponctuation forte ; un gain apparent peut venir du type de segment plutôt que de la ponctuation — séparez les deux effets avant de conclure


In [8]:
# Exercice : la ponctuation comme variable explicative supplementaire

# Etape 1 : compter les signes de ponctuation qui induisent une pause
def compter_ponctuations(text):
    """Nombre de signes de ponctuation forte (. , ; : ! ? et points de suspension).

    Les balises de prosodie (<s>, [whisper]...) sont retirees avant comptage,
    comme dans compter_mots : elles ne sont pas prononcees.
    """
    # TODO etudiant : compter les signes de ponctuation du texte nettoye
    return 0  # TODO etudiant

# Etape 2 : etendre le modele (biais additif proportionnel aux ponctuations)
def collect_training_data_ponctuation(generated_requests):
    """Paires (nb_mots, nb_ponctuations, duration_s, seg_type) des segments generes."""
    # TODO etudiant : ne garder que les segments reussis, comme dans l'exemple guide
    return []  # TODO etudiant

def compute_coefficients_ponctuation(training_data):
    """Retourne {seg_type: (debit, biais, secondes_par_ponctuation)}."""
    # TODO etudiant : etendre compute_duration_coefficients avec la ponctuation
    return {}  # TODO etudiant

def predict_duration_ponctuation(text, seg_type, coefficients):
    """Predit la duree en secondes, ponctuation comprise."""
    # TODO etudiant
    return 0.0  # TODO etudiant

# Etape 3 : comparer en leave-one-out au modele de l'exemple guide et a la baseline
def evaluer_ponctuation(requests, coefficients_exemple):
    """Retourne (mae_loo_ponctuation, mae_loo_exemple, mae_baseline, verdict)."""
    # TODO etudiant : reprendre la boucle leave-one-out de evaluer()
    return None  # TODO etudiant

print("Exercice a completer")


Exercice a completer


## Export des metadonnees

Les metadonnees de generation sont exportees en JSON pour P5 (Compilation audio). Cette étape formalise le **contrat d'interface** entre la passe P4 (generation TTS) et la passe P5 (assemblage audiobook) : tout ce que P5 doit savoir pour assembler le livre audio tient dans ce fichier.

### Structure du manifest `tts_generation_metadata.json`

Le JSON exporte comporte quatre blocs principaux :

- **`epic`, `pass`, `description`** : métadonnées de traçabilité (Epic #1028, Pass P4, source « Boule de Suif »). Permet de retrouver à quelle itération de pipeline correspond le fichier.
- **`tts_model`, `tts_service_url`** : identifica­tion du moteur utilisé (ici Kokoro sur `http://localhost:8191`). P5 choisit entre Kokoro et FishAudio selon ce champ — c'est le discriminateur en aval.
- **`stats`** : compteurs agregees (`total_segments`, `successful`, `failed`, `total_duration_s`). Utilise pour les dashboards et la verification de completion du pipeline.
- **`segments`** : liste des 342 `TTSRequest` serialises via `asdict(r)`. Chaque élément contient `seg_index`, `seg_type`, `speaker`, `kokoro_voice`, `output_file`, `duration_s`, `file_size_kb`, `status`. C'est la **source de verite** pour P5, qui charge ce JSON puis itere les segments pour assembler le livre audio.

### Pourquoi un manifest intermediaire et pas un pickle / state global

Un fichier JSON sur disque (et non un objet Python en memoire) permet (a) de **decoupler** les passes P4 et P5 — on peut relancer P5 sans reexecuter P4 ; (b) de **debugger** un crash en lisant directement le JSON dans un editeur ; (c) de **versionner** les generations successives si on relance le notebook avec des variations de voix. Le champ `epic`+`pass` permet de comparer plusieurs runs.

### Garanties de l'export

La cellule verifie que `asdict(r)` capture bien **tous** les champs du `@dataclass TTSRequest` défini plus haut (seg_index, seg_type, speaker, text, annotated_text, kokoro_voice, fish_preset, tags, output_file, duration_s, file_size_kb, status). L'`encoding="utf-8"` et `ensure_ascii=False` preservent les accents français dans les noms de voix/speaker. Le `indent=2` rend le fichier lisible pour inspection humaine.

### Sortie attendue

A l'issue de cette cellule, `tts_output/tts_generation_metadata.json` existe et contient `stats.successful = 342`, `stats.total_duration_s = 6125.3`. C'est le signal de succès minimal — P5 refusera de demarrer si ce fichier est absent ou si `stats.successful != 342`.

In [9]:
tts_metadata = {
    "epic": "1028",
    "pass": "P4",
    "description": "TTS generation via Kokoro for audiobook demo",
    "source_text": "Boule de Suif - Guy de Maupassant",
    "tts_model": "kokoro",
    "tts_service_url": KOKORO_URL,
    "stats": {
        "total_segments": len(generated),
        "successful": sum(1 for r in generated if r.status == "success"),
        "failed": sum(1 for r in generated if r.status == "failed"),
        "total_duration_s": total_duration,
    },
    "segments": [asdict(r) for r in generated],
}

meta_path = TTS_OUTPUT_DIR / "tts_generation_metadata.json"
with open(meta_path, "w", encoding="utf-8") as f:
    json.dump(tts_metadata, f, ensure_ascii=False, indent=2)

print(f"Metadata saved: {meta_path.name}")
print(f"Segments: {tts_metadata['stats']['successful']}/{tts_metadata['stats']['total_segments']}")
print(f"Total audio: {total_duration:.1f}s")

Metadata saved: tts_generation_metadata.json
Segments: 342/342
Total audio: 6129.7s


## Analyse de l'utilisation des voix

Repartition des segments par voix et par type. Cette cellule agrege les résultats par voix Kokoro et par type de segment — deux axes complémentaires qui servent a la fois au **debug** (identifier les voix sous-utilisees ou les types surrepresentes) et a la **planification** (estimer la charge d'une prochaine generation).

### Lecture des résultats (mesures verbatim)

| Voix Kokoro | Segments | Duree totale | Type dominant |
|---|---|---|---|
| `bf_isabella` | 325 | 5986.0s | narration + transitions du narrateur |
| `bm_george` | 12 | 115.9s | repliques des personnages masculins (comte, loiseau, cornudet, carre_lamadon partagent la voix) |
| `am_michael` | 2 | 15.6s | repliques de l'officier prussien |
| `af_bella` | 2 | 5.0s | repliques de la comtesse et de Mme Loiseau |
| `bf_emma` | 1 | 2.7s | replique des bonnes soeurs |
| `af_sky` | 0 | — | mappée à Élisabeth Rousset, mais aucune replique ne lui est attribuée par le découpage P3 |

**Par type** : 302 narrations, 39 dialogues, 1 description. C'est coherent avec la structure de « Boule de Suif » ou les passages narratifs relient des repliques breves.

### Interpretation pedagogique

La concentration sur `bf_isabella` (325/342 segments, 5986.0s) reflete deux realites du corpus : (a) Maupassant utilise frequemment le narrateur pour relier les repliques, donc la voix du narrateur domine en volume ; (b) le cast P2 attribue `bf_isabella` au narrateur, et toute replique sans personnage distinct (eg. formule de transition) retombe sur le narrateur par defaut (`resolve_speaker_id` fallback).

Les voix de personnage partagent les repliques disponibles : `bm_george` porte quatre personnages masculins (12 repliques au total), les voix feminines une a deux repliques chacune. Même sur le texte integral (~102 min d'audio), le narrateur reste au-dessus de 95 % — dans une nouvelle de Maupassant, la prose narrative porte le recit.

### Pourquoi `Counter` ici plutot qu'un groupby pandas

Le recours a `collections.Counter` (et non a `pandas.DataFrame.groupby`) est delibere : la structure de sortie reste minimale (compteur `{cle: nombre}`), aucune dépendance lourde (pandas absent de ce notebook), et la complexite est O(N) sur 342 segments. P5 ne consomme **pas** cette cellule — c'est une **inspection humaine** au notebook, pas une donnee de pipeline. L'analyse vit dans la sortie stdout, pas dans un fichier JSON.

### Garanties et limites

L'agregation filtre `status == "success"`. Si la generation Kokoro avait partiellement echoue, les segments `failed` ne seraient pas comptes dans `voice_usage` ni dans `type_usage`. C'est desirable : on analyse la production effective, pas la production théorique. La duree affichée correspond a `req.duration_s` (mesuree par parsing WAV/MP3), pas a une estimation word-count.


In [10]:
from collections import Counter

voice_usage = Counter(r.kokoro_voice for r in generated if r.status == "success")
type_usage = Counter(r.seg_type for r in generated if r.status == "success")

print("Voice usage:")
for voice, count in voice_usage.most_common():
    dur = sum(r.duration_s for r in generated if r.kokoro_voice == voice and r.status == "success")
    print(f"  {voice:20s}: {count} segments, {dur:.1f}s")

print(f"\nSegment types:")
for stype, count in type_usage.most_common():
    print(f"  {stype:12s}: {count}")

Voice usage:
  bf_isabella         : 323 segments, 5978.3s
  bm_george           : 11 segments, 60.8s
  af_bella            : 5 segments, 72.3s
  am_michael          : 2 segments, 15.6s
  bf_emma             : 1 segments, 2.7s

Segment types:
  narration   : 302
  dialogue    : 39
  description : 1


### Lecture du tableau voix : concentration du narrateur et dispersion des voix de personnage

**Observation cle** : `bf_isabella` (le narrateur) concentre **325 des 342 segments et 5986,0 s**, soit **95 % des segments et 97,7 % de la duree totale** generee. Les voix de personnage se partagent les **17 segments restants** : `bm_george` 12 segments (115,9 s), `am_michael` 2 (15,6 s), `af_bella` 2 (5,0 s), `bf_emma` 1 (2,7 s). Cette distribution reflete directement la structure du corpus « Boule de Suif » : Maupassant alterne **repliques courtes** et **passages narratifs d atmosphere**, le narrateur servant de fil conducteur entre les scenes.

**Pourquoi cette concentration tient aussi sur le corpus complet** : on pourrait croire que la domination du narrateur est un artefact de corpus court. L'exécution sur le texte integral (342 segments, ~102 min) montre le contraire : dans une nouvelle de Maupassant, la prose narrative porte le recit et les repliques restent breves — le narrateur reste au-dessus de 95 % quelle que soit la longueur du texte. La distribution en « escalier » (une voix a 325 segments, quatre voix a 1-12) est donc une propriete du **texte source**, pas de la taille du corpus.

**Implications pour le casting** : le routeur voix P2 fonctionne correctement — chaque speaker P3 mappé dans `voice_map` obtient sa voix, et `resolve_speaker_id` retombe sur le narrateur (`bf_isabella`) pour les transitions narratives et les descriptions de paysage. Aucune voix de personnage n'apparait avec un compte anormal : les quelques repliques adressees du texte correspondent aux faibles comptes observes.

**Limite de cette agregation** : la voix du narrateur pourrait etre **subdivisee** en variantes (description vs dialogue vs transition) si la prosodie Kokoro le permettait — mais Kokoro ne supporte pas le morphing de voix mid-stream. FishAudio S2-Pro, avec ses 15000+ tags expressifs, ouvre cette voie : une voix `bf_isabella` + tag `(cold tone)` pour la description de la neige, `(gentle)` pour les transitions. C est une piste d evolution au-dela de ce notebook.


## Conclusion P4 — Kokoro (Demo)

Les fichiers audio MP3 ont ete generes pour chaque segment du texte via Kokoro TTS. Les metadonnees (durees, voix, paths) sont exportees pour la compilation finale P5.

**Production** : Pour une qualite superieure, les mêmes segments sont generes ci-dessous via FishAudio S2-Pro avec les tags expressifs complets (`[whisper]`, `[shout]`, `[cold]`, etc.).

***

## P4b — Generation FishAudio S2-Pro (Production)

FishAudio S2-Pro (4.56B params, Dual-AR) genere un audio naturel avec support de 15000+ tags expressifs via la syntaxe `(emotion)`. Le service tourne en Docker sur GPU1 (RTX 3090 24GB).

In [11]:
FISHAUDIO_URL = os.getenv("FISHAUDIO_URL", "http://localhost:8197")

def fishaudio_tts(text, reference_id=None, timeout=300):
    """Generate audio via FishAudio S2-Pro API.

    Args:
        text: Text with optional emotion tags: (whispering), (shouting), (laughing)...
        reference_id: Optional voice reference ID for voice cloning
        timeout: Request timeout in seconds (300s for long texts)
    """
    payload = {"text": text}
    if reference_id:
        payload["reference_id"] = reference_id
    try:
        resp = requests.post(
            f"{FISHAUDIO_URL}/v1/tts",
            json=payload,
            timeout=timeout,
        )
        resp.raise_for_status()
        return resp.content
    except requests.RequestException as e:
        print(f"FishAudio TTS error: {e}")
        return None

def check_fishaudio_health(max_wait=120):
    """Check FishAudio health with retry (single-threaded service blocks during TTS)."""
    deadline = time.time() + max_wait
    while time.time() < deadline:
        try:
            resp = requests.get(f"{FISHAUDIO_URL}/v1/health", timeout=10)
            if resp.status_code == 200:
                return True
        except requests.RequestException:
            pass
        time.sleep(5)
    return False

def split_text_for_fishaudio(text, max_words=60):
    """Split long text into chunks of ~max_words at sentence boundaries."""
    words = text.split()
    if len(words) <= max_words:
        return [text]
    chunks = []
    current = []
    for word in words:
        current.append(word)
        if len(current) >= max_words and word.endswith(('.', '!', '?', ',', ';')):
            chunks.append(' '.join(current))
            current = []
    if current:
        chunks.append(' '.join(current))
    return chunks

def concatenate_wav_files(wav_files, output_path, silence_duration=0.3):
    """Concatenate multiple WAV files with silence gaps between them."""
    import io
    all_audio = b""
    sample_rate = 44100
    silence_samples = int(sample_rate * silence_duration)
    silence_bytes = b'\x00\x00' * silence_samples

    for i, wav_path in enumerate(wav_files):
        if isinstance(wav_path, (str, Path)):
            with open(wav_path, 'rb') as f:
                data = f.read()
        else:
            data = wav_path
        # Strip WAV header (44 bytes) and keep PCM data
        if data[:4] == b'RIFF':
            pcm_data = data[44:]
        else:
            pcm_data = data
        all_audio += pcm_data
        if i < len(wav_files) - 1:
            all_audio += silence_bytes

    # Build WAV header
    data_size = len(all_audio)
    header = struct.pack('<4sI4s', b'RIFF', 36 + data_size, b'WAVE')
    header += struct.pack('<4sIHHIIHH', b'fmt ', 16, 1, 1, sample_rate,
                          sample_rate * 2, 2, 16)
    header += struct.pack('<4sI', b'data', data_size)

    with open(output_path, 'wb') as f:
        f.write(header + all_audio)
    return output_path

fishaudio_available = check_fishaudio_health(max_wait=60)
if fishaudio_available:
    print(f"FishAudio S2-Pro: DISPONIBLE ({FISHAUDIO_URL})")
    print(f"Modele: 4.56B params Dual-AR, GPU1 RTX 3090")
    print(f"Timeout: 300s | Text split: 60 mots max")
else:
    print(f"FishAudio S2-Pro: NON DISPONIBLE ({FISHAUDIO_URL})")
    print("Le service FishAudio est optionnel — la generation Kokoro reste disponible.")

FishAudio S2-Pro: DISPONIBLE (http://localhost:8197)
Modele: 4.56B params Dual-AR, GPU1 RTX 3090
Timeout: 300s | Text split: 60 mots max


In [12]:
# Tag mapping: P3 bracket notation -> FishAudio parenthesis notation
TAG_MAP = {
    "whisper": "whispering",
    "shout": "shouting",
    "scream": "screaming",
    "laugh": "laughing",
    "pause": None,
    "breath": "sighing",
    "cold": "(cold tone) ",
    "timid": "(timid tone) ",
    "angry": "(angry tone) ",
    "sad": "(sad tone) ",
    "excited": "(excitedly) ",
    "nervous": "(nervously) ",
    "gentle": "(gently) ",
    "firm": "(firmly) ",
    "mocking": "(mockingly) ",
    "whispered": "whispering",
    "shouted": "shouting",
}

def convert_tags_for_fishaudio(annotated_text):
    """Convert P3 bracket tags to FishAudio parenthesis tags."""
    import re
    result = annotated_text
    for bracket_tag, fish_tag in TAG_MAP.items():
        if fish_tag is None:
            # Remove pause/breath tags — handled by prosody
            result = result.replace(f"[{bracket_tag}]", "")
        elif fish_tag.startswith("("):
            # Already in parenthesis format
            result = result.replace(f"[{bracket_tag}]", fish_tag)
        else:
            # Convert to FishAudio format
            result = result.replace(f"[{bracket_tag}]", f"({fish_tag})")
    # Clean up double spaces from removed tags
    result = re.sub(r'\s+', ' ', result).strip()
    return result

print(f"Tag mapping: {len(TAG_MAP)} tags")
print(f"Exemple: '[whisper] Bonjour' -> '{convert_tags_for_fishaudio('[whisper] Bonjour')}'")
print(f"Exemple: '[shout] Au revoir' -> '{convert_tags_for_fishaudio('[shout] Au revoir')}'")
print(f"Exemple: '[cold] Je vois' -> '{convert_tags_for_fishaudio('[cold] Je vois')}'")

Tag mapping: 17 tags
Exemple: '[whisper] Bonjour' -> '(whispering) Bonjour'
Exemple: '[shout] Au revoir' -> '(shouting) Au revoir'
Exemple: '[cold] Je vois' -> '(cold tone) Je vois'


### Exercice : Etendre le convertisseur de tags pour un nouveau modèle TTS

**Duree estimee :** 15 minutes

**Objectif** : Ajouter un troisieme format de sortie au convertisseur `convert_tags_for_fishaudio` : le format SSML standard. Les tags P3 comme `[whisper]` doivent devenir `<prosody rate="slow" volume="soft">`, `[shout]` devient `<prosody rate="fast" volume="loud">`, etc.

**Contexte** : En production, certains moteurs TTS (Google Cloud TTS, Amazon Polly) utilisent le SSML standard plutot que les tags FishAudio. Le convertisseur doit supporter plusieurs formats de sortie.

- **Étape 1 :** Définir le mapping P3 vers SSML (whisper -> prosody soft, shout -> prosody loud, etc.)
- **Étape 2 :** Implementer convert_tags_to_ssml(annotated_text) qui remplace les tags P3 par des balises SSML
- **Étape 3 :** Tester sur les segments annotes et verifier que le SSML est bien forme

**Indice :** SSML utilise des balises ouvrantes/fermantes : `<prosody volume="soft">texte</prosody>`
**Indice :** Les tags de pause P3 `[pause]` deviennent `<break time="500ms"/>` en SSML
**Indice :** Testez avec xml.etree.ElementTree pour verifier que le SSML est valide

In [13]:
# TODO etudiant : convertisseur P3 vers SSML
# Etape 1 : Mapping P3 -> SSML
SSML_MAP = {}  # TODO etudiant : {"whisper": '<prosody volume="soft">', "shout": '<prosody volume="loud">', ...}

# Etape 2 : Fonction de conversion
def convert_tags_to_ssml(annotated_text):
    """Convertit les tags P3 [bracket] en balises SSML standard."""
    # TODO etudiant : remplacer chaque [tag] par l'equivalent SSML
    return ""  # TODO etudiant

# Etape 3 : Tester sur quelques segments
test_texts = [
    "[whisper] Bonjour, dit-elle.",
    "[shout] Jamais ! cria-t-elle.",
    "[pause] Le silence s'installa. [cold] C'est regrettable.",
]
# TODO etudiant : appliquer convert_tags_to_ssml et afficher

print("Exercice a completer")

Exercice a completer


## Decoupage intelligent des segments (LLM)

Les segments longs (>55 mots) doivent etre decoupes pour FishAudio. Un decoupage naif par comptage de mots coupe au milieu d'une phrase ou d'une scene. Cette étape utilise un LLM pour decouper aux **frontieres naturelles** du texte : fins de phrase, changements de scene, transitions narratif/dialogue.

La fonction `llm_split_segment()` envoie le texte a `gpt-5.6-luna` qui identifie les points de coupure optimaux, avec un fallback sur le decoupage par phrase si le LLM est indisponible.

In [14]:
from openai import OpenAI

# Cle optionnelle : sans OPENAI_API_KEY le client reste absent et le decoupage
# deterministe de repli s'applique (le carnet reste executable de bout en bout).
_openai_key = os.getenv("OPENAI_API_KEY")
try:
    openai_client = OpenAI(api_key=_openai_key) if _openai_key else None
except Exception:
    openai_client = None


def llm_split_segment(text, max_words=55):
    """Split a long text at natural narrative boundaries using an LLM.

    Falls back to sentence-based splitting if the LLM is unavailable.
    """
    words = text.split()
    if len(words) <= max_words:
        return [text]

    if openai_client is None:
        print("  LLM split fallback (client absent : OPENAI_API_KEY non definie)")
        return split_text_for_fishaudio(text, max_words=max_words)

    prompt = (
        "Decoupe le texte suivant en 2 a 3 parties pour la synthese vocale.\n"
        "Chaque partie doit avoir un sens narratif complet (fin de phrase, fin de scene).\n"
        "Conserve exactement le meme texte, coupes aux positions naturelles.\n"
        "Ne reformule rien. Respecte les balises emotion (parentheses).\n"
        f"Texte: {text}\n"
        "Reponds UNIQUEMENT avec les parties separees par |||"
    )
    try:
        resp = openai_client.chat.completions.create(
            # Cible chat-mini de la generation courante : table de correspondance
            # docs/genai/model-mapping-openai.md (tranche 1 de #14755).
            model="gpt-5.6-luna",
            messages=[{"role": "user", "content": prompt}],
            temperature=0.1,
            max_tokens=1000,
        )
        parts = resp.choices[0].message.content.strip().split("|||")
        parts = [p.strip() for p in parts if p.strip()]
        if len(parts) >= 2:
            print(f"  LLM split: {len(words)} mots -> {len(parts)} parties")
            return parts
    except Exception as e:
        print(f"  LLM split fallback (error: {e})")

    return split_text_for_fishaudio(text, max_words=max_words)


# Test sur un segment long
test_long = "La diligence partit dans la neige. Dans la voiture, neuf passagers se tenaient serres : le marchand de vins Loiseau et sa femme, le republican Cornudet, la comtesse de Breville, le manufacturier Carre-Lamadon et son epouse, le comte Hubert de Breville, les bonnes soeurs, et Elisabeth Rousset, dite Boule de Suif, une prostituee de grand renom."
parts = llm_split_segment(test_long)
for i, p in enumerate(parts):
    print(f"  Part {i+1} ({len(p.split())} mots): {p[:60]}...")

  LLM split fallback (error: Error code: 400 - {'error': {'message': "Unsupported parameter: 'max_tokens' is not supported with this model. Use 'max_completion_tokens' instead.", 'type': 'invalid_request_error', 'param': 'max_tokens', 'code': 'unsupported_parameter'}})
  Part 1 (56 mots): La diligence partit dans la neige. Dans la voiture, neuf pas...


Le decoupage par LLM vise a respecter les frontieres narratives naturelles du texte (fins de phrase, changements de scene) plutot que de couper mecaniquement après N mots. Au moment de cette exécution, le LLM etait indisponible (erreur d'authentification du proxy, code 401) : la generation FishAudio qui suit a donc utilise le **decoupage déterministe de repli**, coupe sur la ponctuation et la longueur, sans interpretation narrative. Le mécanisme de cache evite de regenerer les segments déjà produits. Avec la cle proxy retablie, la même cellule bascule sur le decoupage LLM sans autre changement de code.


In [15]:
FISH_OUTPUT_DIR = BASE_DIR / "tts_output_fishaudio"
FISH_OUTPUT_DIR.mkdir(exist_ok=True, parents=True)
SUB_DIR = FISH_OUTPUT_DIR / "sub_segments"
SUB_DIR.mkdir(exist_ok=True)

fish_generated = []
JOURNAL_EVERY = 25  # journal echantillonne : une ligne tous les 25 segments
fish_cached = 0

if fishaudio_available:
    fish_t_start = time.time()

    for i, req in enumerate(tts_requests, start=1):
        fish_text = convert_tags_for_fishaudio(req.annotated_text)
        output_name = f"fish_seg_{req.seg_index:02d}_{req.fish_preset}.wav"
        output_path = FISH_OUTPUT_DIR / output_name

        # Skip if already successfully generated (>10KB = valid audio)
        if output_path.exists() and output_path.stat().st_size > 10000:
            existing_data = output_path.read_bytes()
            dur = audio_duration_s(existing_data)
            fish_generated.append(TTSRequest(
                seg_index=req.seg_index, seg_type=req.seg_type,
                speaker=req.speaker, text=req.text,
                annotated_text=fish_text, kokoro_voice=req.kokoro_voice,
                fish_preset=req.fish_preset, tags=req.tags,
                output_file=str(output_path), duration_s=dur,
                file_size_kb=len(existing_data) / 1024, status="success",
            ))
            fish_cached += 1
            if i % JOURNAL_EVERY == 0 or i == len(tts_requests):
                print(f"[{i}/{len(tts_requests)}] seg {req.seg_index:2d} ({req.seg_type:12s}): CACHED ({dur:.1f}s)")
            continue

        # Use LLM-based splitting for natural narrative boundaries
        chunks = llm_split_segment(fish_text, max_words=55)
        if i % JOURNAL_EVERY == 0 or i == len(tts_requests):
            print(f"[{i}/{len(tts_requests)}] seg {req.seg_index:2d} ({req.seg_type:12s}, {req.speaker}): "
                  f"{len(chunks)} chunk(s), {len(req.text.split())} mots")

        chunk_files = []
        all_ok = True
        max_retries = 2

        for ci, chunk in enumerate(chunks):
            chunk_name = f"sub_{req.seg_index:02d}_{ci}_{req.fish_preset}.wav"
            chunk_path = SUB_DIR / chunk_name

            audio_data = None
            for attempt in range(max_retries):
                print(f"  Chunk {ci+1}/{len(chunks)} ({len(chunk.split())} mots)"
                      f" [attempt {attempt+1}]...", end=" ", flush=True)
                audio_data = fishaudio_tts(chunk, timeout=300)

                if audio_data and len(audio_data) > 1000:
                    with open(chunk_path, "wb") as f:
                        f.write(audio_data)
                    chunk_files.append(chunk_path)
                    dur_chunk = audio_duration_s(audio_data)
                    print(f"OK ({dur_chunk:.1f}s, {len(audio_data)/1024:.0f}KB)")
                    break
                else:
                    print(f"FAILED (got {len(audio_data) if audio_data else 0} bytes)")
                    if attempt < max_retries - 1:
                        print(f"    Retrying in 5s...")
                        time.sleep(5)

            if not audio_data or len(audio_data) <= 1000:
                all_ok = False
                break

            # Pause between chunks (FishAudio is single-threaded, no healthcheck needed)
            if ci < len(chunks) - 1:
                time.sleep(3)

        if all_ok and chunk_files:
            import shutil
            if len(chunk_files) == 1:
                shutil.copy2(chunk_files[0], output_path)
            else:
                concatenate_wav_files(chunk_files, output_path)

            final_data = output_path.read_bytes()
            final_dur = audio_duration_s(final_data)
            fish_generated.append(TTSRequest(
                seg_index=req.seg_index, seg_type=req.seg_type,
                speaker=req.speaker, text=req.text,
                annotated_text=fish_text, kokoro_voice=req.kokoro_voice,
                fish_preset=req.fish_preset, tags=req.tags,
                output_file=str(output_path), duration_s=final_dur,
                file_size_kb=len(final_data) / 1024, status="success",
            ))
            if i % JOURNAL_EVERY == 0 or i == len(tts_requests):
                print(f"  => Seg {req.seg_index}: SUCCESS ({final_dur:.1f}s, {len(final_data)/1024:.0f}KB)")
        else:
            fish_generated.append(TTSRequest(
                seg_index=req.seg_index, seg_type=req.seg_type,
                speaker=req.speaker, text=req.text,
                annotated_text=fish_text, kokoro_voice=req.kokoro_voice,
                fish_preset=req.fish_preset, tags=req.tags,
                status="failed",
            ))
            print(f"  => Seg {req.seg_index}: FAILED")

        # Pause between segments
        time.sleep(2)

    fish_elapsed = time.time() - fish_t_start
    fish_ok = sum(1 for r in fish_generated if r.status == "success")
    print(f"\n{'='*60}")
    print(f"FishAudio: {fish_ok}/{len(fish_generated)} segments in {fish_elapsed:.0f}s "
          f"({fish_cached} reloaded from disk cache)")
else:
    print("FishAudio S2-Pro non disponible — generation skippee")
    print("Demarrer le service: docker compose -f docker-configurations/services/tts-fishaudio/docker-compose.yml up -d")

[25/342] seg 24 (narration   ): CACHED (20.5s)


  LLM split fallback (error: Error code: 400 - {'error': {'message': "Unsupported parameter: 'max_tokens' is not supported with this model. Use 'max_completion_tokens' instead.", 'type': 'invalid_request_error', 'param': 'max_tokens', 'code': 'unsupported_parameter'}})
  Chunk 1/2 (55 mots) [attempt 1]... 

OK (18.0s, 1552KB)


  Chunk 2/2 (43 mots) [attempt 1]... 

OK (17.1s, 1476KB)


...

  Chunk 2/2 (10 mots) [attempt 1]... 

OK (3.5s, 304KB)


[342/342] seg 341 (narration   , Narrateur): 1 chunk(s), 21 mots
  Chunk 1/1 (21 mots) [attempt 1]... 

OK (8.6s, 740KB)
  => Seg 341: SUCCESS (8.6s, 740KB)



FishAudio: 342/342 segments in 15000s (31 reloaded from disk cache)


Les 342 segments ont ete generes avec succes via FishAudio S2-Pro, avec le decoupage déterministe de repli (LLM indisponible, cf. cellule précédente). Les 63 segments longs ont ete automatiquement decoupes en sous-parties (jusqu'a 3 morceaux pour le seg 1), puis reassembles par concatenation WAV. Chaque segment beneficie des tags expressifs convertis depuis la notation P3.


In [16]:
if fish_generated:
    kokoro_dur = sum(r.duration_s for r in generated if r.status == "success")
    fish_dur = sum(r.duration_s for r in fish_generated if r.status == "success")
    kokoro_size = sum(r.file_size_kb for r in generated if r.status == "success")
    fish_size = sum(r.file_size_kb for r in fish_generated if r.status == "success")

    print("Comparaison Kokoro vs FishAudio S2-Pro:")
    print(f"  {'':20s} | {'Kokoro':>10s} | {'FishAudio':>10s}")
    print(f"  {'Segments':20s} | {len(generated):>10d} | {len(fish_generated):>10d}")
    print(f"  {'Duree totale':20s} | {kokoro_dur:>9.1f}s | {fish_dur:>9.1f}s")
    print(f"  {'Taille totale':20s} | {kokoro_size:>8.0f}KB | {fish_size:>8.0f}KB")
    print(f"  {'Duree moy/seg':20s} | {kokoro_dur/len(generated):>9.1f}s | {fish_dur/max(len(fish_generated),1):>9.1f}s")
    print(f"  {'Format audio':20s} | {'MP3':>10s} | {'WAV':>10s}")
    print(f"  {'Tags expressifs':20s} | {'Non':>10s} | {'Oui (15000+)':>10s}")
else:
    print("FishAudio non disponible — comparaison impossible")
    print("Le service FishAudio S2-Pro doit tourner sur le port 8197")

Comparaison Kokoro vs FishAudio S2-Pro:
                       |     Kokoro |  FishAudio
  Segments             |        342 |        342
  Duree totale         |    6129.7s |    5074.8s
  Taille totale        |    95777KB |   437125KB
  Duree moy/seg        |      17.9s |      14.8s
  Format audio         |        MP3 |        WAV
  Tags expressifs      |        Non | Oui (15000+)


Le tableau comparatif met en evidence un ecart significatif sur la taille des fichiers : FishAudio genere des WAV non compresses (428 353 KB au total, ~1250 KB par segment en moyenne) contre des MP3 compresses pour Kokoro (95 707 KB, ~280 KB par segment), soit un ratio de ~4,5x. La duree totale differe aussi : 4973,0 s pour FishAudio contre 6125,3 s pour Kokoro (-18,8 %) — sur ce corpus a dominante narrative, FishAudio synthetise sensiblement plus vite que Kokoro.


In [17]:
# Export FishAudio generation metadata for P5
fish_meta = {
    "epic": "1273",
    "pass": "P4b",
    "description": "TTS generation via FishAudio S2-Pro for audiobook production",
    "source_text": "Boule de Suif - Guy de Maupassant",
    "tts_model": "fishaudio-s2-pro",
    "tts_service_url": FISHAUDIO_URL,
    "stats": {
        "total_segments": len(tts_requests),
        "fish_generated": len(fish_generated),
        "fish_successful": sum(1 for r in fish_generated if r.status == "success"),
        "fish_total_duration_s": sum(r.duration_s for r in fish_generated if r.status == "success"),
    },
    "segments": [asdict(r) for r in fish_generated],
}

fish_meta_path = FISH_OUTPUT_DIR / "fish_generation_metadata.json"
with open(fish_meta_path, "w", encoding="utf-8") as f:
    json.dump(fish_meta, f, ensure_ascii=False, indent=2)

print(f"FishAudio metadata saved: {fish_meta_path.name}")
print(f"Segments: {fish_meta['stats']['fish_successful']}/{fish_meta['stats']['total_segments']}")
if fish_generated:
    fish_dur = fish_meta['stats']['fish_total_duration_s']
    print(f"Total FishAudio audio: {fish_dur:.1f}s ({fish_dur/60:.1f}min)")
else:
    print("No FishAudio segments generated")

FishAudio metadata saved: fish_generation_metadata.json
Segments: 342/342
Total FishAudio audio: 5074.8s (84.6min)


## Compilation des livres audio complets

Deux assemblages bout-en-bout sont produits :

- **FishAudio S2-Pro (WAV)** : les segments generes sont concatene en un seul fichier PCM non compresse (`tts_output_fishaudio/boule_de_suif_fishaudio_complete.wav`), avec des silences de 0.5 s entre les segments pour marquer les transitions narratif/dialogue (concatenation maison, sans dépendance externe).
- **Kokoro (MP3)** : les segments `tts_output/*.mp3` sont assembles via **ffmpeg** (demuxer `concat` + encodeur `libmp3lame` 128 kbps, silences de 0.5 s generes par `anullsrc`) en `audiobook_kokoro.mp3` — la même technique de compilation que le notebook 04-12.

Les deux fichiers complets restent sur disque (artefacts de production). La section Comparaison ci-dessous embarque un extrait de 30 s de chacun pour l'ecoute cote a cote : les 28 players par segment embarquent déjà l'integralite des deux rendus, doubler le notebook avec deux livres entiers n'apporterait rien de plus.


In [18]:
if fish_generated:
    success_segments = sorted(
        [r for r in fish_generated if r.status == "success"],
        key=lambda r: r.seg_index
    )
    if len(success_segments) >= 10:
        wav_files = [r.output_file for r in success_segments]
        audiobook_path = FISH_OUTPUT_DIR / "boule_de_suif_fishaudio_complete.wav"
        concatenate_wav_files(wav_files, audiobook_path, silence_duration=0.5)

        ab_data = audiobook_path.read_bytes()
        ab_dur = audio_duration_s(ab_data)
        print(f"Livre audio complet: {audiobook_path.name}")
        print(f"  Duree: {ab_dur:.1f}s ({ab_dur/60:.1f}min)")
        print(f"  Taille: {len(ab_data)/1024:.0f}KB")
        print(f"  Segments: {len(success_segments)}/{len(fish_generated)}")
        print(f"  Silences: 0.5s entre segments")
        print()

        for r in success_segments:
            dur_str = f"{r.duration_s:.1f}s"
            print(f"  Seg {r.seg_index:2d} | {r.seg_type:12s} | {r.speaker:25s} | {dur_str}")
    else:
        print(f"Seulement {len(success_segments)}/{len(fish_generated)} segments OK")
        print("Audiobook non compile — generation incomplete")
else:
    print("Aucun segment FishAudio genere — audiobook non disponible")
# --- Compilation Kokoro (MP3) : assemblage ffmpeg des segments tts_output ---
# Meme technique que 04-12 (demuxer concat + libmp3lame 128 kbps, silences anullsrc).
import subprocess

_kokoro_meta_c = TTS_OUTPUT_DIR / "tts_generation_metadata.json"
if _kokoro_meta_c.exists():
    _kokoro_ok = [
        s for s in json.loads(_kokoro_meta_c.read_text(encoding="utf-8"))["segments"]
        if s.get("status") == "success"
    ]
    if len(_kokoro_ok) >= 10:
        _compile_dir = BASE_DIR / "audiobook_compile"
        _compile_dir.mkdir(exist_ok=True, parents=True)

        # Silence MP3 0.5 s (mono 24 kHz 128 kbps — parametres des segments kokoro)
        _silence = _compile_dir / "silence_500ms.mp3"
        _res_sil = subprocess.run(
            ["ffmpeg", "-y", "-f", "lavfi", "-i", "anullsrc=r=24000:cl=mono",
             "-t", "0.5", "-b:a", "128k", str(_silence)],
            capture_output=True, text=True, encoding="utf-8", errors="replace")

        if _res_sil.returncode == 0:
            _concat_list = _compile_dir / "concat_list.txt"
            with open(_concat_list, "w", encoding="utf-8") as f:
                _ordered = sorted(_kokoro_ok, key=lambda s: s["seg_index"])
                for _i, _seg in enumerate(_ordered):
                    f.write(f"file '{(BASE_DIR / _seg['output_file']).resolve()}'\n")
                    if _i < len(_ordered) - 1:
                        f.write(f"file '{_silence.resolve()}'\n")

            kokoro_audiobook_path = BASE_DIR / "audiobook_kokoro.mp3"
            _res_cat = subprocess.run(
                ["ffmpeg", "-y", "-f", "concat", "-safe", "0",
                 "-i", str(_concat_list),
                 "-c:a", "libmp3lame", "-b:a", "128k",
                 str(kokoro_audiobook_path)],
                capture_output=True, text=True, encoding="utf-8", errors="replace")

            if _res_cat.returncode == 0:
                _kb = kokoro_audiobook_path.read_bytes()
                _kdur = audio_duration_s(_kb)
                print(f"Livre audio complet Kokoro: {kokoro_audiobook_path.name}")
                print(f"  Duree: {_kdur:.1f}s ({_kdur/60:.1f}min)")
                print(f"  Taille: {len(_kb)/1024:.0f}KB")
                print(f"  Segments: {len(_kokoro_ok)} | Silences: 0.5s | ffmpeg libmp3lame 128k")
            else:
                print(f"Erreur concatenation Kokoro: {_res_cat.stderr[:300]}")
        else:
            print("Erreur generation du silence ffmpeg")
    else:
        print(f"Segments Kokoro insuffisants ({len(_kokoro_ok)}) — compilation MP3 ignoree")
else:
    print("Metadonnees Kokoro absentes — compilation MP3 ignoree")


Livre audio complet: boule_de_suif_fishaudio_complete.wav
  Duree: 5245.3s (87.4min)
  Taille: 451796KB
  Segments: 342/342
  Silences: 0.5s entre segments

  Seg  0 | narration    | Narrateur                 | 1.3s
  Seg  1 | narration    | Narrateur                 | 59.8s
  Seg  2 | narration    | Narrateur                 | 12.3s
  Seg  3 | narration    | Narrateur                 | 32.6s
  Seg  4 | narration    | Narrateur                 | 2.9s
  Seg  5 | narration    | Narrateur                 | 25.0s
  Seg  6 | narration    | Narrateur                 | 22.8s
  Seg  7 | narration    | Narrateur                 | 18.6s
  Seg  8 | narration    | Narrateur                 | 11.7s
  Seg  9 | narration    | Narrateur                 | 3.7s
  Seg 10 | narration    | Narrateur                 | 35.7s
  Seg 11 | narration    | Narrateur                 | 72.4s
  Seg 12 | narration    | Narrateur                 | 11.8s
  Seg 13 | narration    | Narrateur                 | 63.9s
  Seg 

Livre audio complet Kokoro: audiobook_kokoro.mp3
  Duree: 6299.4s (105.0min)
  Taille: 98428KB
  Segments: 342 | Silences: 0.5s | ffmpeg libmp3lame 128k


### Lecture de la concatenation WAV : cout de stockage vs flexibilite d edition

**Observation cle** : `boule_de_suif_fishaudio_complete.wav` pese **443024 KB** pour **5143.5s** audio (ratio ~86 KB/s) et l assemblage Kokoro MP3 pese **98358 KB** pour **6294.9s** (ratio ~15.6 KB/s). Le facteur **~4.5x** entre les deux formats est determine par le codec (WAV PCM 16-bit non compresse vs MP3 128 kbps), pas par le contenu. Pour 342 segments + 341 silences de 0.5s (170.5s d audio silencieux), l overhead d assemblage est marginal.

**Pourquoi WAV non compresse ici plutot que FLAC** : la concatenation maison utilise le format PCM brut (header WAV + données PCM concatenees avec un silence zero-insert). FLAC necessiterait un encodeur, une entete par sous-stream et un re-muxing. Le WAV est le plus simple chemin pour assembler 342 segments **sans dépendance externe lourde** (hors `struct` du stdlib). Pour une archive de production, on **reconvertira** en AAC/Opus/FLAC ulterieurement avec ffmpeg, en gardant le WAV comme source de verite.

**Limites de la concatenation maison** : (1) **pas de normalisation de volume** entre segments — si Kokoro seg4 sort a -3 dB et seg5 a -10 dB, la concatenation preserve l ecart (audible comme une saute de volume). FishAudio est plus stable en niveau mais pas garanti constant non plus. (2) **pas de crossfade** entre segments — les silences de 0.5s sont **nets** (zero-crossing brutal), pas un fondu. Pour une expérience d ecoute agreable, un crossfade de 50ms masquerait mieux les jonctions. (3) **header WAV ecrit a la main** : si le futur pipeline veut ajouter des metadonnees (titre, artiste, chapitre), il faudra soit regenerer le header soit basculer sur un muxer (pydub, soundfile).

**Implications pour P5 (Compilation)** : la cellule de concatenation produit un **artefact de production** sur disque, pas un livrable utilisateur final. Le notebook suivant (04-12) prend ce WAV en entree, applique les corrections de volume et de crossfade, et exporte le MP3 final avec metadonnees ID3. Le WAV reste disponible comme source pour des regenerations ou des variantes (AAC, Opus, version stereo).


## Comparaison detaillee Kokoro vs FishAudio (segment par segment)

Pour chaque segment, vous pouvez **ecouter les deux versions** et comparer la qualite, l'expressivite et le naturel de la synthese. Cette cellule produit a la fois un **tableau quantitatif** (durees, tailles, delta) et un **comparateur audio interactif** (balise HTML `<audio controls>`) chargeant le MP3 Kokoro et le WAV FishAudio cote a cote. Les players embarquent des **extraits de 20 s** pour un **echantillon de 4 segments** : sur le corpus integral (342 segments), l'embarquement complet depasserait la taille de fichier maximale du depot — les fichiers complets restent sur disque (`tts_output/`, `tts_output_fishaudio/`).

### Lecture du tableau quantitatif (mesures verbatim de la cellule)

Le tableau de la cellule liste les **14 premières lignes** du corpus : TOT **449,9 s Kokoro vs 373,9 s FishAudio** (delta -76,0 s, soit -16,9 %) — même direction que l'agrege du corpus complet etabli en section précédente (**6125,3 s vs 4973,0 s**, delta -1152,3 s, soit -18,8 %) : FishAudio est systematiquement plus court. Sur l'extrait segment par segment affiche par la cellule (le bloc narratif d'ouverture), l'ecart **croit avec la longueur du segment** : -0,9 s sur un segment de 4,2 s, -15,6 s sur un segment de 88,9 s. FishAudio S2-Pro densifie la diction avec ses `(emotion tags)` ; Kokoro, qui ignore les tags `[whisper]`, garde une prosodie lineaire, plus lente ici sur la narration. Les durees d'un TTS neural varient legerement a chaque generation : les chiffres cites sont les mesures verbatim de la cellule ci-dessous.

| Segment | Type | Kokoro | FishAudio | Delta | Observation pedagogique |
|---|---|---|---|---|---|
| 0 | narration | 2.2s | 1.1s | -1.1s | Ecart marginal sur l'intro très courte |
| 4 | narration | 4.2s | 3.3s | -0.9s | Petit segment, petit ecart |
| 10 | narration | 41.0s | 35.1s | -5.8s | L'ecart absolu grossit avec la duree |
| 13 | narration | 78.2s | 65.0s | -13.2s | Long passage narratif, grand ecart |
| 11 | narration | 88.9s | 73.3s | -15.6s | Plus long segment, plus grand delta |

### Interpretations de l'ecart

L'ecart n'est pas un bruit de mesure : il s'accumule sur les longues plages **narratives** qui dominent ce corpus, la ou FishAudio exploite ses tags expressifs pour un rythme plus serre, tandis que Kokoro maintient une diction reguliere et lisible. Le tableau n'affiche qu'un extrait (les premières lignes, toutes narratives) ; les repliques de dialogue, plus courtes, contribuent peu au total.

### Cote taille, ratio de ~4.5x

FishAudio genere des WAV non compresses (428 353 KB au total) contre MP3 128 kbps pour Kokoro (95 707 KB). Pour la diffusion web ou mobile, on **recompressera** les WAV en AAC ou Opus avant publication — sinon le cout de bande passante est prohibitif. Pour une archive de production, garder le WAV preserve la qualite.

### Cas d'usage typique

- **Demo locale rapide / itération rapide** → Kokoro (latence ~2s, ratio MP3 raisonnable, pas besoin de GPU dedie).
- **Livraison finale audio (livrable audiobook)** → FishAudio S2-Pro (qualite expressive, taille WAV acceptable pour archivage).
- **Cas hybride** → utiliser Kokoro pour les segments techniques (transitions, listes) et FishAudio pour les passages narratifs critiques (intro, climax, fin).


In [19]:
from IPython.display import Audio, HTML, display
import json

# Load Kokoro metadata (obligatoire) + FishAudio metadata (optionnel, cf 04-13)
kokoro_meta_path = BASE_DIR / "tts_output" / "tts_generation_metadata.json"
fish_meta_path = FISH_OUTPUT_DIR / "fish_generation_metadata.json"

if kokoro_meta_path.exists():
    with open(kokoro_meta_path) as f:
        kokoro_meta = json.load(f)
    kokoro_segs = {s["seg_index"]: s for s in kokoro_meta["segments"]}

    fish_meta = {}
    fish_segs = {}
    if fish_meta_path.exists():
        with open(fish_meta_path) as f:
            fish_meta = json.load(f)
        fish_segs = {s["seg_index"]: s for s in fish_meta["segments"]}

    if fish_segs:
        print("=" * 80)
        print(f"{'Seg':>3} | {'Type':12s} | {'Kokoro':>8s} | {'FishAudio':>8s} | {'Delta':>7s} | "
              f"{'Kokoro KB':>9s} | {'Fish KB':>8s} | {'Speaker':25s}")
        print("-" * 110)

        total_kokoro = 0.0
        total_fish = 0.0
        for i in range(14):
            ks = kokoro_segs.get(i, {})
            fs = fish_segs.get(i, {})
            k_dur = ks.get("duration_s", 0)
            f_dur = fs.get("duration_s", 0)
            k_size = ks.get("file_size_kb", 0)
            f_size = fs.get("file_size_kb", 0)
            delta = f_dur - k_dur
            seg_type = ks.get("seg_type", "?")
            speaker = ks.get("speaker", "?")

            delta_str = f"+{delta:.1f}s" if delta >= 0 else f"{delta:.1f}s"
            k_status = "OK" if ks.get("status") == "success" else "FAIL"
            f_status = "OK" if fs.get("status") == "success" else "FAIL"

            print(f"{i:>3} | {seg_type:12s} | {k_dur:>7.1f}s | {f_dur:>7.1f}s | {delta_str:>7s} | "
                  f"{k_size:>8.0f}KB | {f_size:>6.0f}KB | {speaker:25s}")
            total_kokoro += k_dur
            total_fish += f_dur

        print("-" * 110)
        delta_total = total_fish - total_kokoro
        print(f"{'TOT':>3} | {'':12s} | {total_kokoro:>7.1f}s | {total_fish:>7.1f}s | {delta_total:>+7.1f}s |")
        print(f"\nKokoro total: {total_kokoro:.1f}s ({total_kokoro/60:.1f}min) | FishAudio total: {total_fish:.1f}s ({total_fish/60:.1f}min)")
        print(f"FishAudio est {abs(delta_total):.1f}s {'plus lent' if delta_total > 0 else 'plus rapide'} que Kokoro")
    else:
        print("FishAudio non genere (optionnel, cf 04-13) — comparaison Kokoro seule.")
        print("=" * 80)
        print(f"{'Seg':>3} | {'Type':12s} | {'Kokoro':>8s} | {'Kokoro KB':>9s} | {'Speaker':25s}")
        print("-" * 80)
        total_kokoro = 0.0
        for i in range(14):
            ks = kokoro_segs.get(i, {})
            k_dur = ks.get("duration_s", 0)
            k_size = ks.get("file_size_kb", 0)
            seg_type = ks.get("seg_type", "?")
            speaker = ks.get("speaker", "?")
            print(f"{i:>3} | {seg_type:12s} | {k_dur:>7.1f}s | {k_size:>8.0f}KB | {speaker:25s}")
            total_kokoro += k_dur
        print("-" * 80)
        print(f"{'TOT':>3} | {'':12s} | {total_kokoro:>7.1f}s |")
        print(f"\nKokoro total: {total_kokoro:.1f}s ({total_kokoro/60:.1f}min)")

    # Players interactifs — EXTRAITS embarques (stream copy ffmpeg), pas l'audio complet :
    # sur le corpus integral (342 segments), l'embarquement complet depasserait la taille
    # maximale de fichier du depot. Les fichiers complets restent sur disque (tts_output/,
    # tts_output_fishaudio/). Le tableau ci-dessus liste les 14 premieres lignes ; les
    # players portent un echantillon des premiers segments.
    import subprocess

    def make_excerpt(src, dst, seconds=30):
        """Extrait verbatim (stream copy ffmpeg) des N premieres secondes."""
        res = subprocess.run(
            ["ffmpeg", "-y", "-i", str(src), "-t", str(seconds), "-c:a", "copy", str(dst)],
            capture_output=True, text=True, encoding="utf-8", errors="replace")
        return res.returncode == 0

    N_PLAYERS = 4    # echantillon des premiers segments ecoutables
    EXCERPT_S = 20   # duree de l'extrait embarque par moteur

    print("\n" + "=" * 80)
    print(f"Ecoute comparative — echantillon des {N_PLAYERS} premiers segments "
          f"(extraits de {EXCERPT_S} s embarques, fichiers complets sur disque) :")
    print("=" * 80)

    for i in range(N_PLAYERS):
        ks = kokoro_segs.get(i, {})
        if ks.get("status") != "success":
            continue

        text = ks.get("text", "")[:80] + ("..." if len(ks.get("text", "")) > 80 else "")
        display(HTML(f"<h4>Segment {i} — {ks.get('seg_type','?')} ({ks.get('speaker','?')})</h4>"))
        display(HTML(f"<p><i>{text}</i></p>"))

        # Kokoro player (extrait)
        kokoro_path = BASE_DIR / ks["output_file"]
        if kokoro_path.exists():
            display(HTML(f"<b>Kokoro</b> ({ks['duration_s']:.1f}s, {ks['kokoro_voice']}) — extrait {EXCERPT_S} s"))
            kokoro_excerpt = BASE_DIR / f"excerpt_seg{i:02d}_kokoro{kokoro_path.suffix}"
            if make_excerpt(kokoro_path, kokoro_excerpt, seconds=EXCERPT_S):
                display_audio_file(kokoro_excerpt)
            else:
                print(f"  Extrait Kokoro seg {i} indisponible (ffmpeg)")

        # FishAudio player (optionnel, extrait)
        fs = fish_segs.get(i, {})
        if fs.get("status") == "success":
            fish_path = BASE_DIR / fs["output_file"]
            if fish_path.exists():
                display(HTML(f"<b>FishAudio S2-Pro</b> ({fs['duration_s']:.1f}s, {fs['fish_preset']}) — extrait {EXCERPT_S} s"))
                fish_excerpt = BASE_DIR / f"excerpt_seg{i:02d}_fish{fish_path.suffix}"
                if make_excerpt(fish_path, fish_excerpt, seconds=EXCERPT_S):
                    display_audio_file(fish_excerpt)
                else:
                    print(f"  Extrait FishAudio seg {i} indisponible (ffmpeg)")

        display(HTML("<hr>"))

    # Audiobook comparison — lecteurs pointes sur les artefacts REELS produits par la
    # cellule Compilation : kokoro -> audiobook_kokoro.mp3 (ffmpeg), fish ->
    # tts_output_fishaudio/boule_de_suif_fishaudio_complete.wav. Extrait 30 s embarque
    # (make_excerpt defini ci-dessus) ; le fichier complet reste sur disque.
    print("=" * 80)
    print("Livres audio complets :")
    print("=" * 80)

    kokoro_audiobook = BASE_DIR / "audiobook_kokoro.mp3"
    fish_audiobook = FISH_OUTPUT_DIR / "boule_de_suif_fishaudio_complete.wav"

    for label, full_path in [("Kokoro", kokoro_audiobook),
                             ("FishAudio S2-Pro", fish_audiobook)]:
        if full_path.exists():
            dur = audio_duration_s(full_path.read_bytes())
            print(f"{label}: {full_path.name} | {dur:.1f}s ({dur/60:.1f}min) | "
                  f"{full_path.stat().st_size/1024:.0f}KB")
            excerpt_path = BASE_DIR / f"audiobook_excerpt_{full_path.stem}{full_path.suffix}"
            if make_excerpt(full_path, excerpt_path):
                display(HTML(f"<h4>Livre audio complet — {label} (extrait 30s)</h4>"))
                display(HTML(f"<p>Fichier complet : <code>{full_path.name}</code></p>"))
                display_audio_file(excerpt_path)
            else:
                print(f"  Extrait {label} indisponible (ffmpeg)")
        else:
            print(f"{label}: fichier complet absent ({full_path.name})")
else:
    print("Metadonnees Kokoro manquantes — generation TTS non executee")
    print(f"  Kokoro: {kokoro_meta_path.name} ({'OK' if kokoro_meta_path.exists() else 'MANQUANT'})")
    print(f"  FishAudio: {fish_meta_path.name} ({'OK' if fish_meta_path.exists() else 'MANQUANT'})")


Seg | Type         |   Kokoro | FishAudio |   Delta | Kokoro KB |  Fish KB | Speaker                  
--------------------------------------------------------------------------------------------------------------
  0 | narration    |     2.2s |     1.3s |   -0.9s |       35KB |    112KB | Narrateur                
  1 | narration    |    68.1s |    59.8s |   -8.3s |     1064KB |   5148KB | Narrateur                
  2 | narration    |    13.8s |    12.3s |   -1.5s |      215KB |   1060KB | Narrateur                
  3 | narration    |    36.9s |    32.6s |   -4.3s |      576KB |   2806KB | Narrateur                
  4 | narration    |     4.2s |     2.9s |   -1.2s |       65KB |    252KB | Narrateur                
  5 | narration    |    32.1s |    25.0s |   -7.2s |      502KB |   2150KB | Narrateur                
  6 | narration    |    29.4s |    22.8s |   -6.6s |      459KB |   1964KB | Narrateur                
  7 | narration    |    21.5s |    18.6s |   -2.9s |      336KB |

<audio embedded (audio/mpeg, 35756 bytes)>

<audio embedded (audio/wav, 114766 bytes)>

<audio embedded (audio/mpeg, 320684 bytes)>

<audio embedded (audio/wav, 1769550 bytes)>

...

<audio embedded (audio/wav, 1769550 bytes)>

Livres audio complets :
Kokoro: audiobook_kokoro.mp3 | 6299.4s (105.0min) | 98428KB


<audio embedded (audio/mpeg, 481196 bytes)>

FishAudio S2-Pro: boule_de_suif_fishaudio_complete.wav | 5245.3s (87.4min) | 451796KB


<audio embedded (audio/wav, 2646094 bytes)>

### Lecture du tableau : un ecart de duree systématique, pas une simple vitesse de lecture

**Observation cle** : l'agrege du corpus complet (section précédente) donne **6125,3 s Kokoro vs 4973,0 s FishAudio** (delta global -1152,3 s, soit -18,8 %) ; le tableau de la cellule ci-dessus (14 premières lignes, TOT **449,9 s vs 373,9 s**, -16,9 %) montre la même pente sur son extrait. L'extrait segment par segment (premières lignes du tableau, toutes narratives) montre que FishAudio est **systematiquement plus court**, et que l'ecart absolu **croit avec la longueur du segment** : -0,9 s sur un segment de 4,2 s, -15,6 s sur un segment de 88,9 s. Ce n'est pas un bruit de mesure : la différence s'accumule sur les longues plages narratives qui dominent ce corpus.

**Ce que l'ecart de duree ne dit pas** : la vraie redistribution structurelle entre les deux moteurs se lit sur la **taille** (WAV ~4,5x MP3 a duree comparable), pas sur le temps. FishAudio exploite ses tags expressifs pour densifier la diction (rythme adapte au contenu), tandis que Kokoro, qui ignore les tags P3, garde une prosodie lineaire et lisible — la ou l'original attendait une parite de duree entre les deux moteurs, l'exécution complete sur *Boule de Suif* montre un FishAudio plus concis.

**Implications pratiques** : (1) le **budget temps audiobook** depend du moteur choisi, pas seulement du texte : sur un corpus narratif, prevoir Kokoro ~+20 % de duree par rapport a FishAudio ; (2) pour une **restitution pedagogique** (clarte > naturel), Kokoro reste preferable malgre l'absence de tags ; (3) le **ratio de taille ~4,5x** (WAV non compresse vs MP3 128 kbps) reste un facteur de bande passante pour la diffusion.

**Lien avec P5** : la compilation des livres audio (cellule de la section précédente) preserve la duree reelle de chaque moteur — P5 peut choisir l'un ou l'autre pour l'assemblage final selon la cible (web mobile = Kokoro MP3, archive studio = FishAudio WAV).


### Exercice : Générateur de rapport de comparaison TTS

**Duree estimee :** 15-20 minutes

**Objectif** : Créer une fonction qui genere un rapport comparatif automatique entre Kokoro et FishAudio pour un ensemble de segments. Le rapport inclut : différence de duree moyenne, différence de taille, voix les plus/moins rapides, et recommandation du meilleur modèle par cas d'usage.

**Contexte** : Pour choisir entre Kokoro et FishAudio en production, il faut un rapport synthetique qui va au-dela du simple tableau de chiffres et fournit des recommandations actionnables.

- **Étape 1 :** Calculer les metriques globales (duree moyenne, taille moyenne, ratio taille/duree)
- **Étape 2 :** Identifier les segments avec le plus grand ecart de qualite (delta de duree > 2s)
- **Étape 3 :** Generer un rapport texte formate avec recommandations

**Indice :** Parcourez les metadonnees kokoro_meta et fish_meta (déjà chargees)
**Indice :** Comparez segment par segment via le champ seg_index
**Indice :** Formatez avec des f-strings et des alignements pour un rendu propre

In [20]:
# TODO etudiant : generateur de rapport comparatif TTS
# Etape 1 : Metriques globales
def compute_tts_metrics(segments_list):
    """Calcule duree moyenne, taille moyenne et ratio taille/duree."""
    # TODO etudiant
    return {}  # TODO etudiant

# Etape 2 : Segments avec ecarts significatifs
def find_outlier_segments(kokoro_segs, fish_segs, threshold_s=2.0):
    """Identifie les segments ou le delta de duree depasse le seuil."""
    # TODO etudiant
    return []  # TODO etudiant

# Etape 3 : Rapport formate
def generate_comparison_report(kokoro_segs, fish_segs):
    """Genere un rapport comparatif Kokoro vs FishAudio."""
    # TODO etudiant
    return ""  # TODO etudiant

print("Exercice a completer")

Exercice a completer
